# Creating a Spatial Relationships Graph from an IFC file

## 1. Import the needed topologicpy Classes

In [1]:
import sys
from topologicpy.Face import Face
from topologicpy.Shell import Shell
from topologicpy.Cluster import Cluster
from topologicpy.Topology import Topology
from topologicpy.Graph import Graph
from topologicpy.Dictionary import Dictionary
from topologicpy.Color import Color
from topologicpy.Helper import Helper
from topologicpy.IFC import IFC

c:\Users\Win11\GraphML_311_env\Lib\site-packages\tqdm\auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


In [2]:
floor_plan = Topology.ByBREPPath(r"C:\Users\sarwj\Downloads\PalazzoDucale.brep")
Topology.Show(floor_plan)
print(floor_plan)
print(Topology.Analyze(floor_plan))

Topology.ByBREPPath - Error: the BREP file is not a valid file. Returning None.
Topology.Show - Error: the input topologies parameter does not contain any valid topology. Returning None.
None
Topology.Analyze - Error: the input topology parameter is not a valid topology. Returning None.
None


In [3]:
face = Cluster.Faces(floor_plan)
shell = Shell.ByFaces(face)
eb = Shell.ExternalBoundary(shell)
ib_list = Shell.InternalBoundaries(shell)
new_face = Face.ByWires(eb, ib_list)
new_face = Topology.RemoveCollinearEdges(new_face)
print(new_face)
Topology.Show(new_face)

Cluster.Faces - Error: The input cluster parameter is not a valid topologic cluster. Returning None.
Shell.ExternalBoundary - Error: The input shell parameter is not a valid Shell. Returning None.
Shell.InternalBoundaries - Error: The input shell parameter is not a valid Shell. Returning None.
Face.ByWires - Error: The input externalBoundary parameter is not a valid topologic wire. Returning None.
caller name: <module>
Topology.RemoveCollinearEdges - Error: The input topology parameter is not a valid topology. Returning None.
caller name: <module>
None
Topology.Show - Error: the input topologies parameter does not contain any valid topology. Returning None.


## 2. Check the TopologicPy version

In [4]:
print("This tutorial requires topologicpy version 0.9.18 or newer.")
print(Helper.Version())

This tutorial requires topologicpy version 0.9.18 or newer.
The version that you are using (0.9.35) is EQUAL TO the latest version available on PyPI.


## 3. Set your renderer:
* Visual studio code: "vscode"
* Google Colab: "colab"
* Browser: "browser"

In [5]:
renderer = "vscode"

## 5. Specify the path to the IFC file and what to include

In [6]:
# Choose your own IFC file if you wish
# Choose your own IFC file if you wish
#ifc_file_path = r"C:\Users\Win11\Desktop\AIA2026\GraphLM\Updated Notebooks\Graph ML -- NOTEBOOKS\Supporting Files\NVW_DCR-LOD100_Arch.ifc"
ifc_file_path = r"C:\Users\Win11\Desktop\AIA2026\GraphLM\Updated Notebooks\Graph ML -- NOTEBOOKS\Supporting Files\NVW_DCR-LOD200_Arch.ifc"

ifc_file = IFC.FileByPath(ifc_file_path)


IFCFastTopology.Parse - Parsed 515000 entities in 5.639s.


## 6. List all the elements in the IFC file

In [7]:
element_types = IFC.ElementTypes(ifc_file, includeCounts = False, silent = False)
element_types = [e.lower() for e in element_types]
for element_type in element_types:
    print(element_type)

ifcapplication
ifcarbitraryclosedprofiledef
ifcarbitraryprofiledefwithvoids
ifcaxis2placement2d
ifcaxis2placement3d
ifcbooleanclippingresult
ifcboundingbox
ifcbuilding
ifcbuildingelementproxy
ifcbuildingstorey
ifccartesianpoint
ifccartesiantransformationoperator3d
ifcclassificationreference
ifccolumn
ifcconnectionsurfacegeometry
ifcconversionbasedunit
ifccurveboundedplane
ifcdimensionalexponents
ifcdirection
ifcdoor
ifcdoorstyle
ifcelementquantity
ifcextrudedareasolid
ifcface
ifcfaceouterbound
ifcgeometricrepresentationcontext
ifclocalplacement
ifcmappeditem
ifcmaterial
ifcmateriallayer
ifcmateriallayerset
ifcmateriallayersetusage
ifcmateriallist
ifcmeasurewithunit
ifcmember
ifcopeningelement
ifcopenshell
ifcorganization
ifcownerhistory
ifcperson
ifcpersonandorganization
ifcplane
ifcpolygonalboundedhalfspace
ifcpolyline
ifcpolyloop
ifcpostaladdress
ifcproductdefinitionshape
ifcproject
ifcpropertyset
ifcpropertysinglevalue
ifcquantityarea
ifcquantitylength
ifcrailing
ifcramp
ifcrectangl

## 6. Specify which spatial elements and spatial relationships you are interested in

In [8]:
includeTypes=["ifcwall", "ifcwallstandardcase", "ifcslab", "ifcwindow", "ifcdoor"]
includeRels = ["overlaps", "touches","within"]

## 7. Import the IFC file

In [9]:
topologies = IFC.TopologiesByPath(ifc_file_path,
                              includeTypes = ["ifcwallstandardcase"],
                              excludeTypes = [],
                              dictionaryMode = "all",
                              clean = False,
                              epsilon = 0.0001,
                              angTolerance = 0.1,
                              tolerance = 0.0001,
                              silent = False)
print(f"Imported {len(topologies)} ifc objects.")

IFCFastTopology.Parse - Parsed 515000 entities in 5.192s.
IFCFastTopology.TopologiesByEntities - Created 501 topologies; skipped 0 products in 6.078s.
Imported 501 ifc objects.


## 8. Show the simplified IFC model

In [10]:
Topology.Show(topologies,
              width=800,
              height=600,
              backgroundColor="black",
              renderer=renderer)

## 9. Create the spatial relationships graph

In [11]:
graph = Graph.BySpatialRelationships(topologies,
                                     include=includeRels,
                                     colorScale="cividis")
print(f"Created a graph with {len(Graph.Vertices(graph))} vertices and {len(Graph.Edges(graph))} edges.")

Created a graph with 501 vertices and 1218 edges.


## 10. Map the vertex types to colours

In [12]:
# Vertices
vertices = Graph.Vertices(graph)
for v in vertices:
    d = Topology.Dictionary(v)
    print(Dictionary.Keys(d), Dictionary.Values(d))
    ifc_type = Dictionary.ValueAtKey(d, "IFC_type", "Unknown")
    try:
        index = element_types.index(ifc_type)
    except:
        index = 0
    vertexColor = Color.AnyToHex(Color.ByValueInRange(index, minValue=0, maxValue=len(element_types)-1, colorScale="cividis"))
    d = Dictionary.SetValuesAtKeys(d, ["IFC_type", "size", "color"], [ifc_type, 10, vertexColor])
    v = Topology.SetDictionary(v, d)


['IFC_global_id', 'IFC_id', 'IFC_key', 'IFC_name', 'IFC_raw_args', 'IFC_type', 'aabb', 'id', 'index'] ['1Nlqm9hRrBYPxNJWgwTE1R', 1711, '#1711', 'Wall', "['1Nlqm9hRrBYPxNJWgwTE1R', ('REF', 5), 'Wall', None, None, ('REF', 1695), ('REF', 1710), None]", 'ifcwallstandardcase', [3300.0, 17850.0, -4500.0, 8700.0, 17875.0, -1500.0], 0, 0]
['IFC_global_id', 'IFC_id', 'IFC_key', 'IFC_name', 'IFC_raw_args', 'IFC_type', 'aabb', 'id', 'index'] ['3hV2uXqDz2Uhp$aaJhM$eS', 24549, '#24549', 'Wall', "['3hV2uXqDz2Uhp$aaJhM$eS', ('REF', 5), 'Wall', None, None, ('REF', 24533), ('REF', 24548), None]", 'ifcwallstandardcase', [-300.0, 500.0, -4500.0, 0.0, 35495.196443, -1500.0], 1, 1]
['IFC_global_id', 'IFC_id', 'IFC_key', 'IFC_name', 'IFC_raw_args', 'IFC_type', 'aabb', 'id', 'index'] ['00FtjcIIX0uQCZN_Sd7w4Y', 24593, '#24593', 'Wall', "['00FtjcIIX0uQCZN_Sd7w4Y', ('REF', 5), 'Wall', None, None, ('REF', 24577), ('REF', 24592), None]", 'ifcwallstandardcase', [12000.0, 500.0, -4500.0, 12300.0, 8500.0, -1500.0], 

## 11. Show the final result

In [13]:
Topology.Show(topologies, graph,
              faceOpacity=0.1,
              sagitta=0.15,
              absolute=False,
              backgroundColor="black",
              vertexSizeKey="size",
              vertexColorKey="color",
              edgeWidthKey="width",
              edgeColorKey="color",
              width=800,
              height=600,
              renderer=renderer)

## 12. Use Pyvis for an alternative visualisation

In [14]:
pyvis_graph = Graph.PyvisGraph(graph, path=r"C:\Users\sarwj\OneDrive - Cardiff University\Desktop\pyvis_graph.html",
                               vertexSizeKey="size",
                               vertexColorKey="color",
                               vertexLabelKey="IFC_type",
                               edgeWeightKey="width",
                               edgeColorKey="color")

Graph.PyvisGraph - Information: Installing required pyvis library.
Graph.PyvisGraph - Information: pyvis library installed correctly.
C:\Users\sarwj\OneDrive - Cardiff University\Desktop\pyvis_graph.html


c:\Users\Win11\GraphML_311_env\Lib\site-packages\topologicpy\Graph.py:22132: UserWarning: Graph.PyvisGraph - Error: Could not save or display the graph. Returning None.
  warnings.warn("Graph.PyvisGraph - Error: Could not save or display the graph. Returning None.")
